In [2]:
import os
import csv
import random
from collections import defaultdict
import re
import pandas as pd

In [3]:
input_folder = r"C:\Users\hanna\ADA\2025\newyorker_caption_contest\data"
cleaned_input_folder =  r"C:\Users\hanna\ADA\2025\newyorker_caption_contest\data_cleaned"

In [4]:
#function used to check if headers are right
EXPECTED_HEADERS = ["rank", "caption", "mean", "precision", "votes", "not_funny", "somewhat_funny", "funny"]

def has_correct_headers(headers):
    """
    Returns True if the CSV headers match the expected headers exactly.
    """
    return headers == EXPECTED_HEADERS

# Iterate over all CSV files
for filename in os.listdir(input_folder):
    if filename.endswith(".csv"):
        input_path = os.path.join(input_folder, filename)

        with open(input_path, "r", encoding="utf-8", newline='') as f:
            reader = csv.reader(f)
            try:
                headers = next(reader)
            except StopIteration:
                print(f"{filename}: file is empty")
                continue

            if not has_correct_headers(headers):
                print(f"{filename}: incorrect headers -> {headers}")

In [7]:
#fixing the files with the missing rank header
#testing on 698.csv first
file_to_fix = "698.csv"  # test on this file only

EXPECTED_HEADERS = ["rank", "caption", "mean", "precision", "votes", "not_funny", "somewhat_funny", "funny"]
MISSING_RANK_HEADERS = ["caption", "mean", "precision", "votes", "not_funny", "somewhat_funny", "funny"]

def fix_missing_rank(file_path):
    """Add a rank column based on descending mean values."""
    rows = []

    # Read the CSV
    with open(file_path, "r", encoding="utf-8", newline='') as f:
        reader = csv.DictReader(f)
        for row in reader:
            try:
                row['mean'] = float(row['mean'])  # convert mean to float for sorting
                rows.append(row)
            except ValueError:
                continue  # skip rows with invalid mean

    # Sort rows by mean descending
    rows.sort(key=lambda x: x['mean'], reverse=True)

    # Write back the CSV with rank
    with open(file_path, "w", encoding="utf-8", newline='') as f:
        writer = csv.writer(f)
        writer.writerow(EXPECTED_HEADERS)  # write header

        for i, row in enumerate(rows):
            writer.writerow([
                i,  # rank
                row['caption'],
                row['mean'],
                row['precision'],
                row['votes'],
                row['not_funny'],
                row['somewhat_funny'],
                row['funny']
            ])

# Check and fix only this file
input_path = os.path.join(input_folder, file_to_fix)

with open(input_path, "r", encoding="utf-8", newline='') as f:
    reader = csv.reader(f)
    try:
        headers = next(reader)
    except StopIteration:
        print(f"{file_to_fix} is empty.")
        headers = []

if headers == MISSING_RANK_HEADERS:
    print(f"{file_to_fix} is missing 'rank'. Fixing it now...")
    fix_missing_rank(input_path)
    print(f"{file_to_fix} has been fixed.")
else:
    print(f"{file_to_fix} already has correct headers.")

698.csv already has correct headers.


In [8]:
def check_corruption(line):
    """
    Params: line (str): A line from the CSV file
    Return a list of reasons if the line is corrupted.
    Criteria:
      1. Line must start with a single number (rank)
      2. Line must end with a numeric value (funny score)
      also removes blank spaces, commas etc from checking
    """
    pattern_starts_with_one_number = re.compile(r"^\d+,")
    pattern_numeric_end = re.compile(r"[-+]?\d*\.?\d+$")

    reasons = []
    stripped = line.strip()

    # --- Check start ---
    if not pattern_starts_with_one_number.match(stripped):
        reasons.append("does not start with single number")

    # --- Check end ---
    if stripped.endswith(',') or stripped.endswith('"') or not stripped:
        # empty, dangling quote, or dangling comma
        reasons.append("ends with non-numeric value")
    else:
        last_field = stripped.split(",")[-1].strip()
        if not pattern_numeric_end.match(last_field):
            reasons.append("ends with non-numeric value")

    return reasons



In [9]:
def check_csv_file_for_corruption(file_num, folder_path):
    """
    Check a CSV file for corrupted lines, given its file number and folder path.
    Prints corrupted lines and a summary at the end.
    Returns corrupted_line_numbers (list): actual 1-based file line numbers
    """
    filename = f"{file_num}.csv"
    file_path = os.path.join(folder_path, filename)

    if not os.path.isfile(file_path):
        print(f" File not found: {file_path}")
        return []

    with open(file_path, "r", encoding="utf-8", newline='') as f:
        lines = f.readlines()

    found_corruption = False
    corrupted_line_numbers = []  # actual file line numbers (1-based)


    print(f"Checking {filename} for corrupted lines...\n")

    for line_number, line in enumerate(lines, start=1):
        if line_number == 1:
            continue  # skip header
        reasons = check_corruption(line)
        if reasons:
            found_corruption = True
            corrupted_line_numbers.append(line_number)

            print(f"{filename}: line {line_number} -> {', '.join(reasons)}")
            print(f"  → {line.strip()[:150]}{'...' if len(line.strip()) > 150 else ''}")

    if not found_corruption:
        print(f" {filename} has no corrupted lines.\n")
    else:
        print("\n--- Summary ---")
        print(f"Total corrupted lines: {len(corrupted_line_numbers)}")
        print(f"Rows with corruption (file line numbers): {corrupted_line_numbers}\n")


    return corrupted_line_numbers


In [10]:
def clean_csv_using_corruption(file_num, folder_path):
    """
    Cleans a CSV file by removing corrupted rows found by check_csv_file_for_corruption.
    Saves the cleaned file in a 'data_cleaned' folder in the same parent directory.
    Uses only the csv module, no pandas.
    """
    # Get corrupted rows (0-based for CSV reading after header)
    corrupted_line_numbers = check_csv_file_for_corruption(file_num, folder_path)



    filename = f"{file_num}.csv"
    file_path = os.path.join(folder_path, filename)

    if not os.path.isfile(file_path):
        print(f"File not found: {file_path}")
        return

    # Prepare clean folder
    parent_dir = os.path.dirname(folder_path)
    clean_folder = os.path.join(parent_dir, "data_cleaned")
    os.makedirs(clean_folder, exist_ok=True)
    cleaned_filename = f"{file_num}_cleaned.csv"
    cleaned_path = os.path.join(clean_folder, cleaned_filename)

    # Read and write CSV, skipping corrupted rows
    with open(file_path, "r", newline="", encoding="utf-8") as infile, \
         open(cleaned_path, "w", newline="", encoding="utf-8") as outfile:

        

        for line_number, line in enumerate(infile, start=1):
            if line_number == 1 or line_number not in corrupted_line_numbers:
                outfile.write(line)

                
                
    return cleaned_path, corrupted_line_numbers

    print(f"{filename}: Cleaned file saved to {cleaned_path}, removed {len(corrupted_rows)} corrupted rows.\n")

In [11]:
check_csv_file_for_corruption(740, input_folder)

Checking 740.csv for corrupted lines...

740.csv: line 79 -> ends with non-numeric value
  → 77,"Just watch.
740.csv: line 80 -> does not start with single number
  → She'll be the one who breaks it.",1.6077127659574468,0.02529241073536315,752,401,251,100
740.csv: line 182 -> ends with non-numeric value
  → 179,"You'd never guess it, but he's the Ceramics & Porcelain appraiser for
740.csv: line 183 -> does not start with single number
  → Antiques Roadshow.",1.5249266862170088,0.036803226973639684,341,198,107,36
740.csv: line 296 -> ends with non-numeric value
  → 292,"Remember to call them ceramics.
740.csv: line 297 -> does not start with single number
  → If you call them china.... Well, just call them ceramics.",1.4836065573770492,0.04325488092184721,244,151,68,25
740.csv: line 649 -> ends with non-numeric value
  → 644,"He sells beautiful pieces, but they're pricey.
740.csv: line 650 -> does not start with single number
  → You wouldn't believe what he has to pay for insurance.",1

[79,
 80,
 182,
 183,
 296,
 297,
 649,
 650,
 720,
 721,
 733,
 734,
 791,
 792,
 935,
 936,
 1078,
 1079,
 1188,
 1189,
 1225,
 1226,
 1333,
 1334,
 1512,
 1513,
 1514,
 1515,
 1670,
 1671,
 1680,
 1681,
 1682,
 1750,
 1751,
 1997,
 1998,
 2064,
 2065,
 2333,
 2334,
 2335,
 2371,
 2372,
 2676,
 2677,
 2678,
 2679,
 2681,
 2682,
 2690,
 2691,
 2704,
 2705,
 2725,
 2726,
 2730,
 2731,
 2732,
 2796,
 2797,
 2898,
 2899,
 3006,
 3007,
 3035,
 3036,
 3062,
 3063,
 3153,
 3154,
 3381,
 3382,
 3383,
 3384,
 3387,
 3388,
 3463,
 3464,
 3478,
 3479,
 3488,
 3489,
 3534,
 3535,
 3591,
 3592,
 3593,
 3759,
 3760,
 3761,
 3762,
 3791,
 3792,
 3879,
 3880,
 3980,
 3981,
 3982,
 4077,
 4078,
 4169,
 4170,
 4218,
 4219,
 4425,
 4426,
 4431,
 4432,
 4438,
 4439,
 4440,
 4608,
 4609,
 4657,
 4658,
 4759,
 4760,
 4945,
 4946,
 4947,
 4973,
 4974,
 5263,
 5264,
 5304,
 5305,
 5318,
 5319,
 5463,
 5464,
 5519,
 5520,
 5545,
 5546,
 5565,
 5566,
 5632,
 5633,
 5729,
 5730,
 5740,
 5741,
 5787,
 5788,
 60

In [12]:
clean_csv_using_corruption(740, input_folder)

Checking 740.csv for corrupted lines...

740.csv: line 79 -> ends with non-numeric value
  → 77,"Just watch.
740.csv: line 80 -> does not start with single number
  → She'll be the one who breaks it.",1.6077127659574468,0.02529241073536315,752,401,251,100
740.csv: line 182 -> ends with non-numeric value
  → 179,"You'd never guess it, but he's the Ceramics & Porcelain appraiser for
740.csv: line 183 -> does not start with single number
  → Antiques Roadshow.",1.5249266862170088,0.036803226973639684,341,198,107,36
740.csv: line 296 -> ends with non-numeric value
  → 292,"Remember to call them ceramics.
740.csv: line 297 -> does not start with single number
  → If you call them china.... Well, just call them ceramics.",1.4836065573770492,0.04325488092184721,244,151,68,25
740.csv: line 649 -> ends with non-numeric value
  → 644,"He sells beautiful pieces, but they're pricey.
740.csv: line 650 -> does not start with single number
  → You wouldn't believe what he has to pay for insurance.",1

('C:\\Users\\hanna\\ADA\\2025\\newyorker_caption_contest\\data_cleaned\\740_cleaned.csv',
 [79,
  80,
  182,
  183,
  296,
  297,
  649,
  650,
  720,
  721,
  733,
  734,
  791,
  792,
  935,
  936,
  1078,
  1079,
  1188,
  1189,
  1225,
  1226,
  1333,
  1334,
  1512,
  1513,
  1514,
  1515,
  1670,
  1671,
  1680,
  1681,
  1682,
  1750,
  1751,
  1997,
  1998,
  2064,
  2065,
  2333,
  2334,
  2335,
  2371,
  2372,
  2676,
  2677,
  2678,
  2679,
  2681,
  2682,
  2690,
  2691,
  2704,
  2705,
  2725,
  2726,
  2730,
  2731,
  2732,
  2796,
  2797,
  2898,
  2899,
  3006,
  3007,
  3035,
  3036,
  3062,
  3063,
  3153,
  3154,
  3381,
  3382,
  3383,
  3384,
  3387,
  3388,
  3463,
  3464,
  3478,
  3479,
  3488,
  3489,
  3534,
  3535,
  3591,
  3592,
  3593,
  3759,
  3760,
  3761,
  3762,
  3791,
  3792,
  3879,
  3880,
  3980,
  3981,
  3982,
  4077,
  4078,
  4169,
  4170,
  4218,
  4219,
  4425,
  4426,
  4431,
  4432,
  4438,
  4439,
  4440,
  4608,
  4609,
  4657,
  4658,


In [13]:
check_csv_file_for_corruption("740_cleaned", cleaned_input_folder)


Checking 740_cleaned.csv for corrupted lines...

 740_cleaned.csv has no corrupted lines.



[]

In [14]:
#now iterrating on the whole data folder
for filename in os.listdir(input_folder):
    if not filename.endswith(".csv"):
        continue

    input_path = os.path.join(input_folder, filename)
    print(f"\nProcessing {filename}...")

    # --- Step 1: Fix missing rank if needed ---
    with open(input_path, "r", encoding="utf-8", newline="") as f:
        reader = csv.reader(f)
        try:
            headers = next(reader)
        except StopIteration:
            print(f"{filename} is empty, skipping.")
            continue

    MISSING_RANK_HEADERS = ["caption", "mean", "precision", "votes", "not_funny", "somewhat_funny", "funny"]
    if headers == MISSING_RANK_HEADERS:
        print(f"{filename} is missing 'rank'. Fixing it now...")
        fix_missing_rank(input_path, filename)
        print(f"{filename} has been fixed.")

    # --- Step 2: Clean corrupted lines ---
    file_num = filename.replace(".csv", "")  # numeric part or full name
    cleaned_path = os.path.join(cleaned_input_folder, f"{file_num}_cleaned.csv")
    
    # Use your cleaning function, but override the output path
    corrupted_line_numbers = check_csv_file_for_corruption(file_num, input_folder)
    
    with open(input_path, "r", encoding="utf-8", newline="") as infile, \
         open(cleaned_path, "w", encoding="utf-8", newline="") as outfile:
        for line_number, line in enumerate(infile, start=1):
            if line_number == 1 or line_number not in corrupted_line_numbers:
                outfile.write(line)

    print(f"{filename}: cleaned file saved to {cleaned_path}")

print(f"\nAll files in {input_folder} have been processed and cleaned files are in {cleaned_input_folder}.")


Processing 510.csv...
Checking 510.csv for corrupted lines...

 510.csv has no corrupted lines.

510.csv: cleaned file saved to C:\Users\hanna\ADA\2025\newyorker_caption_contest\data_cleaned\510_cleaned.csv

Processing 511.csv...
Checking 511.csv for corrupted lines...

 511.csv has no corrupted lines.

511.csv: cleaned file saved to C:\Users\hanna\ADA\2025\newyorker_caption_contest\data_cleaned\511_cleaned.csv

Processing 512.csv...
Checking 512.csv for corrupted lines...

 512.csv has no corrupted lines.

512.csv: cleaned file saved to C:\Users\hanna\ADA\2025\newyorker_caption_contest\data_cleaned\512_cleaned.csv

Processing 513.csv...
Checking 513.csv for corrupted lines...

 513.csv has no corrupted lines.

513.csv: cleaned file saved to C:\Users\hanna\ADA\2025\newyorker_caption_contest\data_cleaned\513_cleaned.csv

Processing 514.csv...
Checking 514.csv for corrupted lines...

 514.csv has no corrupted lines.

514.csv: cleaned file saved to C:\Users\hanna\ADA\2025\newyorker_capti

In [ ]:
for enumerate len(cleaned_input_folder)
check_csv_file_for_corruption("740_cleaned", cleaned_input_folder)

Checking 740_cleaned.csv for corrupted lines...

 740_cleaned.csv has no corrupted lines.



[]

In [ ]:
#checking that all files are clean
all_clean = True  # flag to track if everything is clean

for filename in os.listdir(cleaned_input_folder):
    if not filename.endswith(".csv"):
        continue

    # The file prefix is already file_num_cleaned
    file_num_cleaned = filename.replace(".csv", "")

    # Check corruption
    corrupted_lines = check_csv_file_for_corruption(file_num_cleaned, cleaned_input_folder)
    if corrupted_lines:
        all_clean = False

# Final summary
if all_clean:
    print("\n✅ All files in cleaned_input_folder are clean (no corrupted lines).")
else:
    print("\n❌ Some files have corrupted lines. Check the output above for details.")

Checking 510_cleaned.csv for corrupted lines...

 510_cleaned.csv has no corrupted lines.

Checking 511_cleaned.csv for corrupted lines...

 511_cleaned.csv has no corrupted lines.

Checking 512_cleaned.csv for corrupted lines...

 512_cleaned.csv has no corrupted lines.

Checking 513_cleaned.csv for corrupted lines...

 513_cleaned.csv has no corrupted lines.

Checking 514_cleaned.csv for corrupted lines...

 514_cleaned.csv has no corrupted lines.

Checking 515_cleaned.csv for corrupted lines...

 515_cleaned.csv has no corrupted lines.

Checking 516_cleaned.csv for corrupted lines...

 516_cleaned.csv has no corrupted lines.

Checking 517_cleaned.csv for corrupted lines...

 517_cleaned.csv has no corrupted lines.

Checking 518_cleaned.csv for corrupted lines...

 518_cleaned.csv has no corrupted lines.

Checking 519_cleaned.csv for corrupted lines...

 519_cleaned.csv has no corrupted lines.

Checking 520_cleaned.csv for corrupted lines...

 520_cleaned.csv has no corrupted lines.
